# Learned Stage-Wise Curvature Tuning on Arabic Digits

This notebook evaluates Learned Stage-Wise Curvature Tuning (SW-CT) on the Arabic Handwritten Digits dataset using an ImageNet-pretrained ResNet-50.

Arabic Digits is substantially different from natural-image datasets such as Beans, DTD, Flowers102, and FGVC-Aircraft. The images contain handwritten numerical symbols rather than natural objects or textures. This provides a stronger domain-shift experiment for evaluating whether Learned SW-CT can adapt the curvature of a pretrained network to a visually different downstream task.

The experiments compare four conditions:

1. **Baseline** — the original pretrained ResNet with ReLU activations and a trained downstream classifier.
2. **Single-Parameter Curvature Tuning (S-CT)** — one global beta selected through validation-based exhaustive search.
3. **Learned SW-CT with fixed initialization** — four trainable stage-wise beta parameters initialized at 0.78.
4. **Learned SW-CT with random initialization** — four trainable stage-wise beta parameters independently initialized between 0.70 and 0.99.

Each condition is evaluated using seeds 42, 43, and 44.

Experiments are conducted for both 20 and 30 epochs to determine whether additional optimization improves performance or changes the learned stage-wise beta values.

Wall-clock execution time is also recorded to compare the computational cost of Baseline, S-CT, and Learned SW-CT.

In [1]:
!nvidia-smi

Mon Oct  5 08:22:38 2026       
+-----------------------------------------------------------------------------------------+
| NVIDIA-SMI 580.178.04             Driver Version: 580.178.04     CUDA Version: 13.0     |
+-----------------------------------------+------------------------+----------------------+
| GPU  Name                 Persistence-M | Bus-Id          Disp.A | Volatile Uncorr. ECC |
| Fan  Temp   Perf          Pwr:Usage/Cap |           Memory-Usage | GPU-Util  Compute M. |
|                                         |                        |               MIG M. |
|=========================================+========================+======================|
|   0  Tesla T4                       Off |   00000000:00:04.0 Off |                    0 |
| N/A   50C    P8             12W /   70W |       0MiB /  15360MiB |      0%      Default |
|                                         |                        |                  N/A |
+-----------------------------------------+-----

In [1]:
%cd /content

!git clone -b main \
    https://github.com/NiftySnek173/research-curvature-tuning.git

%cd /content/research-curvature-tuning/src/curvature-tuning

!git branch --show-current
!git log -1 --oneline

/content
Cloning into 'curvature-tuning-research'...


remote: Enumerating objects: 592, done.
remote: Counting objects: 100% (264/264), done.
remote: Compressing objects: 100% (128/128), done.
remote: Total 592 (delta 166), reused 198 (delta 115), pack-reused 328 (from 1)
Receiving objects: 100% (592/592), 17.47 MiB | 7.04 MiB/s, done.
Resolving deltas: 100% (297/297), done.
/content/curvature-tuning-research/src/curvature-tuning
stage-wise-ct
6ec796c (HEAD -> stage-wise-ct, origin/stage-wise-ct, origin/HEAD) updated the notebook with outputs


## Environment Setup

The repository dependencies are installed before running the experiments.

After installation, the Colab runtime should be restarted so that the required package versions are loaded correctly.

In [2]:
%pip install -q -r requirements.txt
%pip install --force-reinstall --no-cache-dir "numpy==1.26.3"

  Preparing metadata (setup.py) ... done
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 15.7/15.7 MB 88.0 MB/s eta 0:00:0000:0100:01
  Installing build dependencies ... done
  Getting requirements to build wheel ... done
  Installing backend dependencies ... done
  Preparing metadata (pyproject.toml) ... done
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 42.4/42.4 kB 1.9 MB/s eta 0:00:00
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 57.6/57.6 kB 3.0 MB/s eta 0:00:00
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 89.9/89.9 kB 4.2 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 64.9/64.9 kB 3.6 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 133.2/133.2 kB 7.2 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 2.3/2.3 MB 71.2 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 78.4/78.4 kB 4.2 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 12.7/12.7 MB 101.3 MB/s eta 0:00:0000:010:01
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 8.3/

In [11]:
%cd /content/research-curvature-tuning/src/curvature-tuning

import os
import torch

os.environ["WANDB_MODE"] = "disabled"

print("Working directory:", os.getcwd())
print("PyTorch:", torch.__version__)
print("CUDA available:", torch.cuda.is_available())

if torch.cuda.is_available():
    print("GPU:", torch.cuda.get_device_name(0))

/content/curvature-tuning-research/src/curvature-tuning
Working directory: /content/curvature-tuning-research/src/curvature-tuning
PyTorch: 2.6.0+cu124
CUDA available: True
GPU: NVIDIA L4


## Arabic Digits Dataset

Before running the experiments, the Arabic Digits data loaders are checked to confirm that the downstream dataset can be loaded correctly.

The same dataset split and random seed protocol are used for Baseline, S-CT, and Learned SW-CT so that the methods are compared under the same conditions.

In [12]:
from utils.data import get_data_loaders

train_loader, test_loader, val_loader = get_data_loaders(
    "imagenet_to_arabic-digits",
    train_batch_size=32,
    test_batch_size=128,
    seed=42,
)

print("Train samples:", len(train_loader.dataset))
print("Validation samples:", len(val_loader.dataset))
print("Test samples:", len(test_loader.dataset))

images, labels = next(iter(train_loader))

print("Image batch shape:", images.shape)
print("Label batch shape:", labels.shape)
print("Labels:", labels[:10])

/content/.venv/lib/python3.11/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm
Processing train set: 100%|██████████| 60001/60001 [00:14<00:00, 4154.96it/s]
Generating train split: 60000 examples [00:14, 4008.36 examples/s]
Processing test set: 100%|██████████| 10001/10001 [00:02<00:00, 4190.40it/s]
Generating test split: 10000 examples [00:02, 4110.14 examples/s]


Train samples: 48000
Validation samples: 12000
Test samples: 10000
Image batch shape: torch.Size([32, 3, 224, 224])
Label batch shape: torch.Size([32])
Labels: tensor([4, 5, 6, 2, 5, 9, 3, 5, 6, 5])


# ResNet-50 Experiments

ResNet-50 is evaluated first because it was used during the initial development of Learned SW-CT.

The experiment compares Baseline, S-CT, fixed-initialization SW-CT, and random-initialization SW-CT.

All methods use the same ImageNet-pretrained backbone, Arabic Digits dataset split, experimental seeds, and downstream training protocol.

## ResNet-50 — 20-Epoch Evaluation

The first evaluation uses 20 training epochs.

This provides the primary reference experiment and maintains compatibility with the earlier Learned SW-CT work.

### Methods

**Baseline**

The pretrained ResNet-50 retains its original ReLU activations. The backbone is frozen and only the downstream classifier is trained.

**S-CT**

The original Single-Parameter Curvature Tuning method searches over a single beta shared throughout the network. Candidate beta values from 0.70 to 1.00 are evaluated using validation performance, and the best candidate is evaluated on the test set.

The recorded S-CT execution time includes the complete beta search rather than only the final selected beta.

**Learned SW-CT — Fixed Initialization**

Four trainable beta parameters are assigned to the four ResNet stages. All four begin at beta = 0.78.

This preserves the initialization used in the original Learned SW-CT experiments.

**Learned SW-CT — Random Initialization**

Four trainable stage-wise beta parameters are initialized independently between 0.70 and 0.99.

The random initialization is generated deterministically from the experiment seed. This allows the experiment to test whether Learned SW-CT depends on the fixed 0.78 starting value while remaining reproducible.

In [ ]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-05 17:32:42.879 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_arabic-digits_resnet50_seed42_epochs20.log
2026-10-05 17:32:42.882 | INFO     | __main__:main:78 - Running on cuda
2026-10-05 17:34:08.142 | INFO     | __main__:main:105 - Testing baseline...
2026-10-05 17:34:08.219 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-05 17:34:08.220 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-05 17:37:25.552 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.354883, Accuracy: 6.25%
2026-10-05 17:37:25.985 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.270961, Accuracy: 22.49%
2026-10-05 17:37:26.448 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.101368, Accuracy: 42.04%
2026-10-05 17:37:26.929 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.898898, Accuracy: 54.24%
2026-10-05 17:37:27.440 | INFO     | train:train_epoch:47 - Epoch 1, Step 400,

In [ ]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-05 22:19:32.287 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_arabic-digits_resnet50_seed43_epochs20.log
2026-10-05 22:19:32.291 | INFO     | __main__:main:78 - Running on cuda
2026-10-05 22:20:56.530 | INFO     | __main__:main:105 - Testing baseline...
2026-10-05 22:20:56.605 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-05 22:20:56.605 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-05 22:24:23.444 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.305411, Accuracy: 12.50%
2026-10-05 22:24:23.850 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.264525, Accuracy: 18.87%
2026-10-05 22:24:24.322 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.093356, Accuracy: 40.44%
2026-10-05 22:24:24.800 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.891484, Accuracy: 52.86%
2026-10-05 22:24:25.268 | INFO     | train:train_epoch:47 - Epoch 1, Step 400

In [ ]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-06 03:36:54.540 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_arabic-digits_resnet50_seed44_epochs20.log
2026-10-06 03:36:54.543 | INFO     | __main__:main:78 - Running on cuda
2026-10-06 03:38:07.755 | INFO     | __main__:main:105 - Testing baseline...
2026-10-06 03:38:07.802 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-06 03:38:07.802 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-06 03:41:27.659 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.285849, Accuracy: 12.50%
2026-10-06 03:41:28.035 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.218277, Accuracy: 25.87%
2026-10-06 03:41:28.417 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.054260, Accuracy: 43.53%
2026-10-06 03:41:28.804 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.858637, Accuracy: 54.26%
2026-10-06 03:41:29.194 | INFO     | train:train_epoch:47 - Epoch 1, Step 400

### Learned SW-CT with Fixed Beta Initialization

The original Learned SW-CT configuration is first reproduced using the fixed initialization:

\[[\beta_1,\beta_2,\beta_3,\beta_4]=[0.78,0.78,0.78,0.78].\]

The initial value is only a starting point. During training, the four beta parameters are optimized independently together with the downstream classifier.

These runs provide the reference against which random initialization will be compared.

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-06 08:05:25.099 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed42_epochs20_initfixed0.78_betalr0.01.log
2026-10-06 08:05:25.169 | INFO     | __main__:main:302 - Running on cuda
2026-10-06 08:06:39.284 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-06 08:06:39.285 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-06 08:06:39.354 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-06 08:06:39.355 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-06 08:06:39.356 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-06 08:06:40.662 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.411696, Accuracy: 9.38%
2026-10-06 08:07:37.056 | INFO     | train:train_e

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-06 13:40:29.848 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed43_epochs20_initfixed0.78_betalr0.01.log
2026-10-06 13:40:29.906 | INFO     | __main__:main:302 - Running on cuda
2026-10-06 13:41:49.499 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-06 13:41:49.500 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-06 13:41:49.559 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-06 13:41:49.560 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-06 13:41:49.561 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-06 13:41:50.826 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.367231, Accuracy: 15.62%
2026-10-06 13:42:47.519 | INFO     | train:train_

In [14]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-11 09:41:42.464 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed44_epochs20_initfixed0.78_betalr0.01.log
2026-10-11 09:41:42.517 | INFO     | __main__:main:302 - Running on cuda
2026-10-11 09:42:35.566 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-11 09:42:35.567 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-11 09:42:35.630 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-11 09:42:35.630 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-11 09:42:35.631 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-11 09:42:36.721 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.408815, Accuracy: 6.25%
2026-10-11 09:43:15.127 | INFO     | train:train_e

### Learned SW-CT with Random Beta Initialization

The fixed beta = 0.78 initialization may raise the question of whether Learned SW-CT performs well only because its starting point was informed by the earlier S-CT experiments.

To test this dependency, each of the four stage-wise beta parameters is now initialized independently from a uniform distribution between 0.70 and 0.99.

The initialization is reproducible: the random generator is seeded using the experiment seed. Therefore, each seed always receives the same initial beta vector.

If random initialization produces similar performance to the fixed 0.78 experiment, this provides evidence that the Learned SW-CT result is not dependent on a single hand-selected initialization.

In [15]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-11 13:15:23.366 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed42_epochs20_initrandom_betalr0.01.log
2026-10-11 13:15:23.419 | INFO     | __main__:main:302 - Running on cuda
2026-10-11 13:16:16.298 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-11 13:16:16.298 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-11 13:16:16.360 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-11 13:16:16.361 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-11 13:16:16.361 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-11 13:16:17.457 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.397518, Accuracy: 12.50%
2026-10-11 13:16:56.108 | INFO     | 

In [16]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-11 16:49:08.202 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed43_epochs20_initrandom_betalr0.01.log
2026-10-11 16:49:08.256 | INFO     | __main__:main:302 - Running on cuda
2026-10-11 16:50:00.775 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-11 16:50:00.775 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-11 16:50:00.837 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-11 16:50:00.838 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-11 16:50:00.838 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-11 16:50:01.943 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.369114, Accuracy: 9.38%
2026-10-11 16:50:40.570 | INFO     |

In [17]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-11 20:22:46.868 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed44_epochs20_initrandom_betalr0.01.log
2026-10-11 20:22:46.921 | INFO     | __main__:main:302 - Running on cuda
2026-10-11 20:23:40.102 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-11 20:23:40.102 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-11 20:23:40.164 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-11 20:23:40.165 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-11 20:23:40.166 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-11 20:23:41.264 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.429126, Accuracy: 3.12%
2026-10-11 20:24:19.892 | INFO     |

# ResNet-50 — 30-Epoch Evaluation

The same experiments are now repeated for 30 epochs.

The purpose of increasing the training budget is to determine whether the 20-epoch results are limited by insufficient optimization.

If a method improves substantially with 30 epochs, this suggests that additional optimization is useful. If performance remains similar, it indicates that the method has largely stabilized within the original 20-epoch training budget.

All other experimental settings remain unchanged.

For random-initialization SW-CT, the same seed produces exactly the same initial four-beta vector in both the 20-epoch and 30-epoch experiments. Therefore, initialization is held constant while the training duration changes.

Execution time is again recorded to measure the computational cost of extending training from 20 to 30 epochs.

In [18]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-11 23:56:27.230 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_arabic-digits_resnet50_seed42_epochs30.log
2026-10-11 23:56:27.231 | INFO     | __main__:main:78 - Running on cuda
2026-10-11 23:57:19.832 | INFO     | __main__:main:105 - Testing baseline...
2026-10-11 23:57:19.875 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-11 23:57:19.875 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-11 23:58:58.380 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.354870, Accuracy: 6.25%
2026-10-11 23:58:58.606 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.270949, Accuracy: 22.49%
2026-10-11 23:58:58.825 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.101361, Accuracy: 42.06%
2026-10-11 23:58:59.037 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.898881, Accuracy: 54.23%
2026-10-11 23:58:59.256 | INFO     | train:train_epoch:47 - Epoch 1, Step 400,

In [19]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-12 03:09:49.771 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_arabic-digits_resnet50_seed43_epochs30.log
2026-10-12 03:09:49.773 | INFO     | __main__:main:78 - Running on cuda
2026-10-12 03:10:42.529 | INFO     | __main__:main:105 - Testing baseline...
2026-10-12 03:10:42.573 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-12 03:10:42.573 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-12 03:12:21.246 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.305392, Accuracy: 12.50%
2026-10-12 03:12:21.480 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.264512, Accuracy: 18.90%
2026-10-12 03:12:21.696 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.093339, Accuracy: 40.44%
2026-10-12 03:12:21.909 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.891455, Accuracy: 52.88%
2026-10-12 03:12:22.125 | INFO     | train:train_epoch:47 - Epoch 1, Step 400

In [20]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-12 06:23:19.567 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_arabic-digits_resnet50_seed44_epochs30.log
2026-10-12 06:23:19.568 | INFO     | __main__:main:78 - Running on cuda
2026-10-12 06:24:12.279 | INFO     | __main__:main:105 - Testing baseline...
2026-10-12 06:24:12.322 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-12 06:24:12.323 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-12 06:25:50.982 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.285871, Accuracy: 12.50%
2026-10-12 06:25:51.211 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.218291, Accuracy: 25.87%
2026-10-12 06:25:51.434 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.054270, Accuracy: 43.56%
2026-10-12 06:25:51.658 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.858631, Accuracy: 54.29%
2026-10-12 06:25:51.878 | INFO     | train:train_epoch:47 - Epoch 1, Step 400

In [21]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-12 09:37:04.750 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed42_epochs30_initfixed0.78_betalr0.01.log
2026-10-12 09:37:04.803 | INFO     | __main__:main:302 - Running on cuda
2026-10-12 09:37:57.432 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-12 09:37:57.433 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-12 09:37:57.495 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-12 09:37:57.496 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-12 09:37:57.496 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-12 09:37:58.602 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.411709, Accuracy: 9.38%
2026-10-12 09:38:37.239 | INFO     | train:train_e

In [22]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-12 14:56:55.209 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed43_epochs30_initfixed0.78_betalr0.01.log
2026-10-12 14:56:55.264 | INFO     | __main__:main:302 - Running on cuda
2026-10-12 14:57:47.745 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-12 14:57:47.745 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-12 14:57:47.809 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-12 14:57:47.810 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-12 14:57:47.810 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-12 14:57:48.918 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.367243, Accuracy: 15.62%
2026-10-12 14:58:27.586 | INFO     | train:train_

In [23]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-12 20:16:49.938 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed44_epochs30_initfixed0.78_betalr0.01.log
2026-10-12 20:16:49.992 | INFO     | __main__:main:302 - Running on cuda
2026-10-12 20:17:42.920 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-12 20:17:42.920 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-12 20:17:42.982 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-12 20:17:42.983 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-12 20:17:42.984 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-12 20:17:44.092 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.408815, Accuracy: 6.25%
2026-10-12 20:18:22.745 | INFO     | train:train_e

In [24]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-13 01:36:38.121 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed42_epochs30_initrandom_betalr0.01.log
2026-10-13 01:36:38.174 | INFO     | __main__:main:302 - Running on cuda
2026-10-13 01:37:30.496 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-13 01:37:30.496 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-13 01:37:30.559 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-13 01:37:30.560 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-13 01:37:30.560 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-13 01:37:31.675 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.397518, Accuracy: 12.50%
2026-10-13 01:38:10.325 | INFO     | 

In [25]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-13 06:56:30.370 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed43_epochs30_initrandom_betalr0.01.log
2026-10-13 06:56:30.423 | INFO     | __main__:main:302 - Running on cuda
2026-10-13 06:57:23.445 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-13 06:57:23.446 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-13 06:57:23.508 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-13 06:57:23.509 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-13 06:57:23.509 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-13 06:57:24.621 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.369114, Accuracy: 9.38%
2026-10-13 06:58:03.268 | INFO     |

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds arabic-digits \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-13 12:16:18.491 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_arabic-digits_resnet50_seed44_epochs30_initrandom_betalr0.01.log
2026-10-13 12:16:18.543 | INFO     | __main__:main:302 - Running on cuda
2026-10-13 12:17:10.674 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-13 12:17:10.675 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
2026-10-13 12:17:10.738 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-13 12:17:10.739 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-13 12:17:10.739 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-13 12:17:11.849 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.429126, Accuracy: 3.12%
2026-10-13 12:17:50.503 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, L